# Spark homework

## Instructions
**To be submitted on  may 18th 2026 23h59 at the latest**

- Work in collaboration with a partner
- Create a git repository on moule for your projects and give reporter access to user @sirangel
- Submit your work by February 28th (last commit on project will be checked)
- You will be asked to present your work

## What to submit
You will implement the project in a single jupyter notebook. Your notebook should not only contain your **code** and **plots**, it should be readable as a **report** (use Markdown cells interleaved with your code cells). You have to explain the data that you chose and each of the analyses you are doing, as well as interpret the results. 

You are required to export your notebook (completely executed with all displayed outputs) **as HTML** and make sure the HTML alone can **display all the plots**. In particular when using plotly, running the following cell before exporting to HTML might be necessary:

In [1]:
import plotly
plotly.offline.init_notebook_mode()

**You will submit a single jupyter notebook, already executed, with displayed outputs, and its html export**

## Dataset

In this homework you will find an open source dataset using Google dataset search ( https://datasetsearch.research.google.com/). You can use another search tool if you prefer.

Read this notebook entirely before choosing your dataset, as not all datasets are suitable to the required  exploration.

The dataset you download will most probably be in CSV or JSON format. Make sure your dataset weights at least a few gigabytes (it could be larger if your laptop and your internet connection allows you to download it and store it)


Your dataset has to feature
- some temporal information (such as year, date or timestamp)
- some geographical information in the form of GPS coordinates
- both numerical (continuous) and categorical columns


Whatever the framework you use, `CSV` and `JSON` files prove hard to handle. 
After downloading the appropriate files (this takes time, but this is routine), a first step will consist in converting the csv files into a more Spark friendly format such as `parquet`.

Saving into one of those formats require decisions about bucketing, partitioning and so on. Such decisions influence performance. It is your call.

## Tools

You **might** need the following tools in order to work with GPS coordinates and to plot things easily.

In [2]:
! apt-get update

Hit:1 http://ports.ubuntu.com/ubuntu-ports focal InRelease
Get:2 http://ports.ubuntu.com/ubuntu-ports focal-updates InRelease [128 kB]
Get:3 http://ports.ubuntu.com/ubuntu-ports focal-backports InRelease [128 kB]
Get:4 http://ports.ubuntu.com/ubuntu-ports focal-security InRelease [128 kB]
Fetched 383 kB in 2s (230 kB/s)
Reading package lists... Done


In [3]:
! apt-get install -y libgdal-dev

Reading package lists... Done
Building dependency tree       
Reading state information... Done
libgdal-dev is already the newest version (3.0.4+dfsg-1build3).
0 upgraded, 0 newly installed, 0 to remove and 58 not upgraded.


In [4]:
!pip install fiona==1.8.19


[notice] A new release of pip is available: 24.3.1 -> 25.0.1
[notice] To update, run: python3 -m pip install --upgrade pip


In [5]:
!pip install geojson geopandas==0.12


[notice] A new release of pip is available: 24.3.1 -> 25.0.1
[notice] To update, run: python3 -m pip install --upgrade pip


In [6]:
!pip install plotly geopy


[notice] A new release of pip is available: 24.3.1 -> 25.0.1
[notice] To update, run: python3 -m pip install --upgrade pip


In [7]:
!pip install ipyleaflet


[notice] A new release of pip is available: 24.3.1 -> 25.0.1
[notice] To update, run: python3 -m pip install --upgrade pip


In order to find the longitude and latitude of a particular place on earth you can use a service like [geojson.io](http://geojson.io/) (draw a point or a region on the map you'll get their coordinates).

For this homework **we will let you decide on the tools to use** (except for Spark which is mandatory) and to **find out information all by yourself**.

**Do not forget to add Markdown cells to**
- introduce your project and describe your dataset
- explain each code cell and each plot
- explain the choices you made

# Loading data as parquet files

You may organise your data into multiple `parquet` files, if you can split your data naturally by some key.
Note that when data is converted to `parquet` its size can be drastically reduced.


CSV files can contain corrupted lines. You may have to work in order to perform ETL (Extract-Transform-Load) in order obtain a properly typed data frame.

You are invited to proceed as follows:

1. Try to read the CSV file without imposing a schema. 
1. Inspect the inferred schema. Do you agree with Spark's typing decision?
1. If needed correct the schema and read again the data
1. Save the data into parquet files
1. In the rest of your work, **you will only use the parquet files you created**, not the csv files.

**Hint.** Don't forget to ask `Spark` to use all the memory and ressources from your computer.

**Hint.** Don't forget that you should specify a partitioning column and a number of partitions when creating the parquet files.


**Hint.** When working on this, ask yourself and answer the following questions:

1. What is the `StorageLevel` of the dataframe after reading the csv files?
1. What is the number of partitions of the dataframe? 
1. Is it possible to tune this number at loading time? 
1. Why would we want to modify the number of partitions when creating the parquet files?

In [8]:
from pyspark.sql import SparkSession
import os
import psutil

try:
    spark.stop()
except:
    pass

# Ressources machine
cores      = os.cpu_count()
ram_total  = psutil.virtual_memory().total          # octets
ram_gb     = ram_total / (1024 ** 3)

driver_gb  = max(4, int(ram_gb * 0.75))             # mémoire Spark
offheap_gb = max(1, int(ram_gb * 0.10))             # mémoire off-heap
result_gb  = max(1, int(driver_gb * 0.25))          # taille max des résultats

print(f"RAM totale   : {ram_gb:.1f} GB")
print(f"Driver memory: {driver_gb}g  ({driver_gb/ram_gb*100:.0f}% RAM)")
print(f"Off-heap     : {offheap_gb}g")
print(f"Max result   : {result_gb}g")
print(f"Cores        : {cores}")

# Création de la session Spark
spark = (
    SparkSession.builder
    .appName("TaxiOptimized")
    .master(f"local[{cores}]")

    # Mémoire Spark
    .config("spark.driver.memory",          f"{driver_gb}g")
    .config("spark.driver.maxResultSize",   f"{result_gb}g")
    .config("spark.memory.offHeap.enabled", "true")
    .config("spark.memory.offHeap.size",    f"{offheap_gb}g")
    .config("spark.memory.fraction",        "0.8")
    .config("spark.memory.storageFraction", "0.3")

    # Partitions Spark
    .config("spark.sql.shuffle.partitions",                    str(cores * 4))
    .config("spark.sql.files.maxPartitionBytes",               "134217728")
    .config("spark.sql.files.openCostInBytes",                 "4194304")

    # Optimisation Spark
    .config("spark.sql.adaptive.enabled",                      "true")
    .config("spark.sql.adaptive.coalescePartitions.enabled",   "true")
    .config("spark.sql.adaptive.skewJoin.enabled",             "true")

    # Sérialisation Spark
    .config("spark.serializer",              "org.apache.spark.serializer.KryoSerializer")
    .config("spark.kryoserializer.buffer.max", "512m")

    .getOrCreate()
)

spark.sparkContext.setLogLevel("WARN")
print("\nSpark version:", spark.version)
print("Driver memory confirmé:", spark.conf.get("spark.driver.memory"))

RAM totale   : 3.8 GB
Driver memory: 4g  (105% RAM)
Off-heap     : 1g
Max result   : 1g
Cores        : 8

Spark version: 3.0.1
Driver memory confirmé: 4g


In [ ]:
input_path = "/opt/polynote/notebooks/Taxi.csv"

df_raw = (
    spark.read
    .option("header", "true")
    .option("multiLine", "false")
    .option("mode", "PERMISSIVE")
    .csv(input_path)
)

df_raw.printSchema()
df_raw.limit(5).show()

In [ ]:
from pyspark.sql import functions as F

# Nettoyer les noms de colonnes
df = df_raw.toDF(*[c.strip().replace(" ", "_") for c in df_raw.columns])

# Colonnes à convertir en double
tab_double_casting = [
    "Trip_Miles", "Fare", "Tips", "Tolls", "Extras", "Trip_Total",
    "Pickup_Centroid_Latitude", "Pickup_Centroid_Longitude",
    "Dropoff_Centroid_Latitude", "Dropoff_Centroid_Longitude"
]

# Garder les colonnes utiles
df_cleaned = df.select(
    "Trip_ID",
    "Taxi_ID",
    "Trip_Start_Timestamp",
    "Trip_End_Timestamp",
    "Trip_Seconds",
    "Trip_Miles",
    "Pickup_Census_Tract",
    "Dropoff_Census_Tract",
    "Pickup_Community_Area",
    "Dropoff_Community_Area",
    "Fare",
    "Tips",
    "Tolls",
    "Extras",
    "Trip_Total",
    "Payment_Type",
    "Company",
    "Pickup_Centroid_Latitude",
    "Pickup_Centroid_Longitude",
    "Dropoff_Centroid_Latitude",
    "Dropoff_Centroid_Longitude",
)

# Enlever les doublons
df_cleaned = df_cleaned.dropDuplicates(["Trip_ID"])

# Convertir les colonnes numériques
for element in tab_double_casting:
    df_cleaned = df_cleaned.withColumn(
        element,
        F.regexp_replace(
            F.regexp_replace(F.col(element), r"[ $]", ""),
            ",", "."
        ).cast("double")
    )

# Convertir Trip_Seconds en entier
df_cleaned = df_cleaned.withColumn(
    "Trip_Seconds",
    F.col("Trip_Seconds").cast("int")
)

# Convertir les dates
df_cleaned = (
    df_cleaned
    .withColumn(
        "Trip_Start_Timestamp",
        F.to_timestamp(F.col("Trip_Start_Timestamp"), "MM/dd/yyyy hh:mm:ss a")
    )
    .withColumn(
        "Trip_End_Timestamp",
        F.to_timestamp(F.col("Trip_End_Timestamp"), "MM/dd/yyyy hh:mm:ss a")
    )
)

# Enlever les lignes invalides
df_cleaned = df_cleaned.filter(
    (F.col("Trip_Start_Timestamp").isNotNull()) &
    (F.col("Trip_End_Timestamp").isNotNull()) &
    (F.col("Trip_End_Timestamp") > F.col("Trip_Start_Timestamp")) &
    (F.col("Trip_Seconds") > 0) &
    (F.col("Trip_Miles") > 0) &
    (F.col("Fare") >= 0) &
    (F.col("Tips") >= 0) &
    (F.col("Tolls") >= 0) &
    (F.col("Extras") >= 0) &
    (F.col("Trip_Total") >= 0)
)

df_cleaned = df_cleaned.dropna(subset=[
    "Trip_ID",
    "Trip_Start_Timestamp",
    "Trip_End_Timestamp",
    "Trip_Seconds",
    "Trip_Miles",
    "Trip_Total",
    "Pickup_Centroid_Latitude",
    "Pickup_Centroid_Longitude",
    "Dropoff_Centroid_Latitude",
    "Dropoff_Centroid_Longitude",
])

print(f"Lignes après nettoyage : {df_cleaned.count()}")
df_cleaned.printSchema()

In [ ]:
output_path = "/opt/polynote/notebooks/taxi_parquet"

# Ajouter le mois du trajet
df_cleaned = df_cleaned.withColumn(
    "Trip_month",
    F.month(F.col("Trip_Start_Timestamp"))
)

# Repartir les données par mois
# Limiter le nombre de fichiers écrits
df_cleaned = df_cleaned.repartition(12, "Trip_month")

print(f"Nombre de partitions Spark avant écriture : {df_cleaned.rdd.getNumPartitions()}")

# Sauvegarder en Parquet
(
    df_cleaned
    .write
    .mode("overwrite")
    .partitionBy("Trip_month")
    .parquet(output_path)
)

print(f"Données écrites dans : {output_path}")

In [9]:
# Lire les données Parquet
output_path = "/opt/polynote/notebooks/taxi_parquet"
df = spark.read.parquet(output_path)

print(f"Nombre de lignes : {df.count()}")
df.printSchema()
df.show(5, truncate=False)

Nombre de lignes : 4013042
root
 |-- Trip_ID: string (nullable = true)
 |-- Taxi_ID: string (nullable = true)
 |-- Trip_Start_Timestamp: timestamp (nullable = true)
 |-- Trip_End_Timestamp: timestamp (nullable = true)
 |-- Trip_Seconds: integer (nullable = true)
 |-- Trip_Miles: double (nullable = true)
 |-- Pickup_Census_Tract: string (nullable = true)
 |-- Dropoff_Census_Tract: string (nullable = true)
 |-- Pickup_Community_Area: string (nullable = true)
 |-- Dropoff_Community_Area: string (nullable = true)
 |-- Fare: double (nullable = true)
 |-- Tips: double (nullable = true)
 |-- Tolls: double (nullable = true)
 |-- Extras: double (nullable = true)
 |-- Trip_Total: double (nullable = true)
 |-- Payment_Type: string (nullable = true)
 |-- Company: string (nullable = true)
 |-- Pickup_Centroid_Latitude: double (nullable = true)
 |-- Pickup_Centroid_Longitude: double (nullable = true)
 |-- Dropoff_Centroid_Latitude: double (nullable = true)
 |-- Dropoff_Centroid_Longitude: double (nu

**Your Answers here**

# Exploring your data

From now on, you will be using **the parquet files you created**.

If computation is too slow, you may want to filter your data first to concentrate only on a portion of it (for instance restric to given time intervals). In that case remember to cache/persist the result, so that it is not recomputed every time you use it.


**Hint.** In order to build appealing graphics, you may stick to `matplotlib + seaborn`, you can use also
`plotly`, which is used a lot to build interactive graphics, but you can use whatever you want.

Select some geographical boundaries (such as longitute and latitude intervals, or a set of cities/regions, or similar). Using these boundaries, **filter your data** to rows whose geographical properties fall in these boundaries. Within this filtered data, chose a relvant column `c` and count the number of rows for each value of `c`; make a plot of that.

In [10]:
df.printSchema()

root
 |-- Trip_ID: string (nullable = true)
 |-- Taxi_ID: string (nullable = true)
 |-- Trip_Start_Timestamp: timestamp (nullable = true)
 |-- Trip_End_Timestamp: timestamp (nullable = true)
 |-- Trip_Seconds: integer (nullable = true)
 |-- Trip_Miles: double (nullable = true)
 |-- Pickup_Census_Tract: string (nullable = true)
 |-- Dropoff_Census_Tract: string (nullable = true)
 |-- Pickup_Community_Area: string (nullable = true)
 |-- Dropoff_Community_Area: string (nullable = true)
 |-- Fare: double (nullable = true)
 |-- Tips: double (nullable = true)
 |-- Tolls: double (nullable = true)
 |-- Extras: double (nullable = true)
 |-- Trip_Total: double (nullable = true)
 |-- Payment_Type: string (nullable = true)
 |-- Company: string (nullable = true)
 |-- Pickup_Centroid_Latitude: double (nullable = true)
 |-- Pickup_Centroid_Longitude: double (nullable = true)
 |-- Dropoff_Centroid_Latitude: double (nullable = true)
 |-- Dropoff_Centroid_Longitude: double (nullable = true)
 |-- Trip_mo

In [ ]:
from pyspark.sql import functions as F
df.orderBy(F.col("Trip_Miles").desc()).show(12)

In [11]:
from pyspark.sql import functions as F
from pyspark.sql import Window
import plotly.express as px

# Zones utilisées
downtown_areas = [8, 32, 28, 33]

# Créer les zones
df_zones = (
    df
    .filter(
        F.col("Pickup_Community_Area").isNotNull() &
        F.col("Company").isNotNull()
    )
    .withColumn(
        "Zone",
        F.when(F.col("Pickup_Community_Area") == 76, "O'Hare Airport")
         .when(F.col("Pickup_Community_Area") == 56, "Midway Airport")
         .when(F.col("Pickup_Community_Area").isin(downtown_areas), "Centre-ville")
         .otherwise(None)
    )
    .filter(F.col("Zone").isNotNull())
)

# Compter les trajets par zone et compagnie
df_rank = (
    df_zones
    .groupBy("Zone", "Company")
    .agg(F.count("Trip_ID").alias("nb_trips"))
)

# Calculer la part de marché
w_total = Window.partitionBy("Zone")
w_rank = Window.partitionBy("Zone").orderBy(F.desc("nb_trips"))

df_top = (
    df_rank
    .withColumn("total_zone_trips", F.sum("nb_trips").over(w_total))
    .withColumn(
        "market_share",
        (F.col("nb_trips") / F.col("total_zone_trips")) * 100
    )
    .withColumn("rank", F.row_number().over(w_rank))
    .filter(F.col("rank") <= 8)
    .select("Zone", "Company", "nb_trips", "market_share", "rank")
)

# Passer en Pandas
df_pd = df_top.toPandas()

# Raccourcir les noms
df_pd["Company_short"] = (
    df_pd["Company"]
    .str.replace("Taxi Affiliation Services", "Taxi Aff.", regex=False)
    .str.replace("Dispatch Taxi Affiliation", "Dispatch", regex=False)
    .str.replace("Chicago Independents", "Chicago Ind.", regex=False)
    .str.replace("Transit Administrative Center Inc", "Transit Admin.", regex=False)
    .str.replace("Blue Ribbon Taxi Association", "Blue Ribbon", regex=False)
    .str.replace("Taxicab Insurance Agency Llc", "Taxicab Ins.", regex=False)
    .str.replace("Sun Taxi Association", "Sun Taxi", regex=False)
    .str.replace("Globe Taxi Association", "Globe Taxi", regex=False)
)

# Texte affiché dans les barres
df_pd["market_share_label"] = df_pd["market_share"].round(1).astype(str) + "%"

# Ordre des zones
zone_order = ["Centre-ville", "Midway Airport", "O'Hare Airport"]

# Trier
df_pd = df_pd.sort_values(
    ["Zone", "market_share"],
    ascending=[True, True]
)

# Graphique
fig = px.bar(
    df_pd,
    x="market_share",
    y="Company_short",
    color="Zone",
    facet_col="Zone",
    facet_col_spacing=0.08,
    orientation="h",
    category_orders={
        "Zone": zone_order
    },
    title="Part de marché des compagnies de taxi par zone de pickup",
    labels={
        "market_share": "Part de marché (%)",
        "Company_short": "Compagnie",
        "Zone": "Zone"
    },
    text="market_share_label",
    hover_data={
        "Company": True,
        "nb_trips": True,
        "market_share": ":.1f",
        "Zone": True,
        "Company_short": False,
        "market_share_label": False
    },
    height=700,
    width=1200
)

# Texte plus lisible
fig.update_traces(
    textposition="outside",
    cliponaxis=False
)

# Chaque facette garde ses propres compagnies
fig.update_yaxes(matches=None)

# Axe x plus large pour laisser la place aux labels
fig.update_xaxes(
    range=[0, df_pd["market_share"].max() * 1.25],
    title_text="Part de marché (%)"
)

# Nettoyer les titres des facettes
fig.for_each_annotation(
    lambda a: a.update(text=a.text.replace("Zone=", ""))
)

# Mise en page
fig.update_layout(
    showlegend=False,
    title_x=0.5,
    bargap=0.25,
    margin=dict(l=120, r=80, t=90, b=80)
)

fig.show()

Going back to unfiltered data
1. Identify a column which contains outliers, i.e. values which  are pretty rare, and show how you found these outliers.

1. Plot the distribution of this column (using an histogram for instance). Then restrict the plot to a range that does not include outliers.

1. What is the largest value in this column? 

In [ ]:
#A revoir


In [12]:
from pyspark.sql import functions as F
import plotly.express as px
import pandas as pd

# Garder les lignes GPS valides
df_geo = (
    df
    .filter(
        (F.col("Trip_Miles") > 0) &
        (F.col("Trip_Total") >= 0) &
        F.col("Pickup_Centroid_Latitude").isNotNull() &
        F.col("Pickup_Centroid_Longitude").isNotNull() &
        F.col("Dropoff_Centroid_Latitude").isNotNull() &
        F.col("Dropoff_Centroid_Longitude").isNotNull()
    )
)

# Calculer la distance GPS
R = 6371.0  # rayon de la Terre en km

df_geo = (
    df_geo
    .withColumn("lat1", F.radians(F.col("Pickup_Centroid_Latitude")))
    .withColumn("lat2", F.radians(F.col("Dropoff_Centroid_Latitude")))
    .withColumn("lon1", F.radians(F.col("Pickup_Centroid_Longitude")))
    .withColumn("lon2", F.radians(F.col("Dropoff_Centroid_Longitude")))
    .withColumn("dlat", F.col("lat2") - F.col("lat1"))
    .withColumn("dlon", F.col("lon2") - F.col("lon1"))
    .withColumn(
        "haversine_a",
        F.pow(F.sin(F.col("dlat") / 2), 2) +
        F.cos(F.col("lat1")) *
        F.cos(F.col("lat2")) *
        F.pow(F.sin(F.col("dlon") / 2), 2)
    )
    .withColumn(
        "gps_distance_km",
        2 * R * F.asin(F.sqrt(F.col("haversine_a")))
    )
    .drop("lat1", "lat2", "lon1", "lon2", "dlat", "dlon", "haversine_a")
)

# Convertir les miles en km
df_geo = (
    df_geo
    .withColumn("trip_km", F.col("Trip_Miles") * 1.60934)
    .filter(F.col("gps_distance_km") > 0.5)  # évite les trajets GPS trop courts / bruités
    .withColumn("distance_ratio", F.col("trip_km") / F.col("gps_distance_km"))
)

# Repérer les outliers
df_geo = (
    df_geo
    .withColumn(
        "outlier_trip_miles",
        F.when(
            (F.col("distance_ratio") > 2.5) |
            (F.col("distance_ratio") < 0.5),
            1
        ).otherwise(0)
    )
    .withColumn(
        "outlier_type",
        F.when(F.col("distance_ratio") > 2.5, "Trip_Miles too high vs GPS")
         .when(F.col("distance_ratio") < 0.5, "Trip_Miles too low vs GPS")
         .otherwise("Normal")
    )
)

# Compter les outliers
counts = (
    df_geo
    .groupBy("outlier_trip_miles", "outlier_type")
    .count()
    .orderBy("outlier_trip_miles", F.desc("count"))
    .toPandas()
)

print("Répartition des outliers Trip_Miles via GPS :")
print(counts.to_string(index=False))

# Histogramme du ratio
sample_ratio = (
    df_geo
    .select("distance_ratio", "outlier_trip_miles")
    .filter(
        F.col("distance_ratio").isNotNull() &
        (F.col("distance_ratio") > 0) &
        (F.col("distance_ratio") <= 10)
    )
    .sample(False, 0.05, seed=42)
    .toPandas()
)

fig_ratio = px.histogram(
    sample_ratio,
    x="distance_ratio",
    color="outlier_trip_miles",
    nbins=150,
    title="Distribution du ratio Trip_Miles / distance GPS",
    labels={
        "distance_ratio": "Ratio trip_km / gps_distance_km",
        "outlier_trip_miles": "Outlier"
    },
    opacity=0.75
)

fig_ratio.add_vline(x=0.5, line_dash="dash", annotation_text="Seuil bas = 0.5")
fig_ratio.add_vline(x=2.5, line_dash="dash", annotation_text="Seuil haut = 2.5")

fig_ratio.show()

# Histogramme de Trip_Miles
sample_miles = (
    df_geo
    .select("Trip_Miles", "outlier_trip_miles")
    .filter((F.col("Trip_Miles") > 0) & (F.col("Trip_Miles") <= 50))
    .sample(False, 0.05, seed=42)
    .toPandas()
)

fig_miles = px.histogram(
    sample_miles,
    x="Trip_Miles",
    color="outlier_trip_miles",
    nbins=150,
    title="Distribution de Trip_Miles : trajets normaux vs outliers GPS",
    labels={
        "Trip_Miles": "Distance déclarée (miles)",
        "outlier_trip_miles": "Outlier GPS"
    },
    opacity=0.75
)

fig_miles.show()

# Statistiques générales
stats = df_geo.agg(
    F.count("*").alias("nb_rows"),
    F.sum("outlier_trip_miles").alias("nb_outliers"),
    F.avg("distance_ratio").alias("avg_distance_ratio"),
    F.expr("percentile_approx(distance_ratio, 0.5)").alias("median_distance_ratio"),
    F.max("Trip_Miles").alias("max_trip_miles"),
    F.max("distance_ratio").alias("max_distance_ratio")
).toPandas()

print("\nStatistiques globales :")
print(stats.to_string(index=False))

# Afficher les trajets suspects
df_suspects = (
    df_geo
    .filter(F.col("outlier_trip_miles") == 1)
    .select(
        "Trip_ID",
        "Trip_Miles",
        "trip_km",
        "gps_distance_km",
        "distance_ratio",
        "outlier_type",
        "Trip_Total",
        "Pickup_Community_Area",
        "Dropoff_Community_Area",
        "Pickup_Centroid_Latitude",
        "Pickup_Centroid_Longitude",
        "Dropoff_Centroid_Latitude",
        "Dropoff_Centroid_Longitude"
    )
    .orderBy(F.desc("distance_ratio"))
    .limit(20)
)

df_suspects.show(20, truncate=False)

# Afficher les cas inverses
df_suspects_low = (
    df_geo
    .filter(F.col("distance_ratio") < 0.5)
    .select(
        "Trip_ID",
        "Trip_Miles",
        "trip_km",
        "gps_distance_km",
        "distance_ratio",
        "outlier_type",
        "Trip_Total",
        "Pickup_Community_Area",
        "Dropoff_Community_Area"
    )
    .orderBy("distance_ratio")
    .limit(20)
)

df_suspects_low.show(20, truncate=False)

Répartition des outliers Trip_Miles via GPS :
 outlier_trip_miles               outlier_type   count
                  0                     Normal 3498447
                  1  Trip_Miles too low vs GPS   64929
                  1 Trip_Miles too high vs GPS   49177



Statistiques globales :
 nb_rows  nb_outliers  avg_distance_ratio  median_distance_ratio  max_trip_miles  max_distance_ratio
 3612553       114106            1.235868               1.175459           241.3          185.922542
+----------------------------------------+----------+------------------+------------------+------------------+--------------------------+----------+---------------------+----------------------+------------------------+-------------------------+-------------------------+--------------------------+
|Trip_ID                                 |Trip_Miles|trip_km           |gps_distance_km   |distance_ratio    |outlier_type              |Trip_Total|Pickup_Community_Area|Dropoff_Community_Area|Pickup_Centroid_Latitude|Pickup_Centroid_Longitude|Dropoff_Centroid_Latitude|Dropoff_Centroid_Longitude|
+----------------------------------------+----------+------------------+------------------+------------------+--------------------------+----------+---------------------+-------

Let's look at what Spark does for these computations

1. Use the `explain` method or have a look at the [Spark UI](http://localhost:4040/SQL/) to analyze the job. You should be able to assess 
    - Parsed Logical Plan
    - Analyzed Logical Plan
    - Optimized Logical Plan
    - Physical Plan
1. Do the Analyzed Logical Plan and Optimized Logical Plan differ? Spot the differences if any. How would a RDBMS proceed with such a query?
1. How does the physical plan differ from the Optimized Logical Plan?  
1. Inspect the stages on [Spark UI](http://localhost:4040/stages/stage). How many *stages* are necessary to complete the Spark job? What are the roles of `HashAggregate` and `Exchange hashpartitioning`?
1. Does the physical plan perform `shuffle` operations? If yes how many?
1. What are tasks with respect to stages (in Spark language)? How many tasks are your stages made of?

In [ ]:
# Code à compléter

**Your Answers here**

Now, compute the following and produce relevant plots. Choose columns so as the following analyses are meaningful:

1. Choose a column `cat` having only a few categorical values. Then a column `c` having continuous numerical values. Break down the distribution of `c` by the values of `cat` (i.e. count the number of occurrences of each `c` value with each `cat` value). Choose an appropriate plot type that highlits how the total `c` count is broken down in categories. 
1. Count the number of distinct values of `c`
1. Compute and display at least two other columns as a function of `c`.

In [13]:
from pyspark.sql import functions as F
import plotly.express as px
import pandas as pd

# Préparer les données
df_price = (
    df
    .filter(
        (F.col("Trip_Miles") > 0) &
        (F.col("Trip_Total") > 0) &
        F.col("Company").isNotNull()
    )
    .withColumn("price_per_mile", F.col("Trip_Total") / F.col("Trip_Miles"))
    .filter(F.col("price_per_mile").isNotNull())
    .filter((F.col("price_per_mile") >= 0) & (F.col("price_per_mile") <= 50))
    .withColumn("price_bucket", F.floor(F.col("price_per_mile")).cast("int"))
    .filter((F.col("price_bucket") >= 0) & (F.col("price_bucket") <= 20))
)

# Garder les principales compagnies
top_companies = (
    df_price
    .groupBy("Company")
    .count()
    .orderBy(F.desc("count"))
    .limit(8)
    .select("Company")
    .rdd.flatMap(lambda x: x)
    .collect()
)

# Graphique empilé
df_stacked_pd = (
    df_price
    .filter(F.col("Company").isin(top_companies))
    .groupBy("price_bucket", "Company")
    .agg(F.count("Trip_ID").alias("count"))
    .select("price_bucket", "Company", "count")
    .orderBy("price_bucket")
    .toPandas()
)

fig1 = px.bar(
    df_stacked_pd,
    x="price_bucket",
    y="count",
    color="Company",
    title="Distribution de price_per_mile par compagnie",
    labels={
        "price_bucket": "Prix/mile (tranche entière, $)",
        "count": "Nombre de trajets",
        "Company": "Compagnie"
    },
    height=500
)
fig1.show()

# Compter les valeurs distinctes
n_distinct = df_price.select("price_per_mile").distinct().count()
print(f"Valeurs distinctes de price_per_mile : {n_distinct}")

# Boxplot par compagnie
sample_box = (
    df_price
    .filter(F.col("Company").isin(top_companies))
    .select("Company", "price_per_mile")   # correction importante
    .sample(False, 0.02, seed=42)
    .toPandas()
)

fig2 = px.box(
    sample_box,
    x="Company",
    y="price_per_mile",
    color="Company",
    title="Boxplot price_per_mile par compagnie",
    labels={
        "price_per_mile": "Prix/mile ($)",
        "Company": "Compagnie"
    },
    height=500
)
fig2.update_xaxes(tickangle=30)
fig2.show()

# Moyennes par tranche de prix
df_agg = (
    df_price
    .groupBy("price_bucket")
    .agg(
        F.avg("Trip_Miles").alias("avg_trip_miles"),
        F.avg("Trip_Seconds").alias("avg_trip_seconds")
    )
    .select("price_bucket", "avg_trip_miles", "avg_trip_seconds")
    .orderBy("price_bucket")
    .toPandas()
)

fig3 = px.line(
    df_agg,
    x="price_bucket",
    y="avg_trip_miles",
    title="Distance moyenne selon le prix/mile",
    labels={
        "price_bucket": "Prix/mile ($)",
        "avg_trip_miles": "Distance moyenne (miles)"
    },
    markers=True
)
fig3.show()

fig4 = px.line(
    df_agg,
    x="price_bucket",
    y="avg_trip_seconds",
    title="Durée moyenne selon le prix/mile",
    labels={
        "price_bucket": "Prix/mile ($)",
        "avg_trip_seconds": "Durée moyenne (secondes)"
    },
    markers=True
)
fig4.show()

Valeurs distinctes de price_per_mile : 343395


# Looking at time series

Identify a temporal column (such as date, year, hour, day of the week etc.) `t`, and at least three different continuous numerical columns `n` and `a` and `m`. Compute and plot the count of`n`  the average of `a` and the median of `m` as functions of `t`. Make sure they correspond to properties whose evolution over time is interesting to analyze. 


In [14]:
from pyspark.sql import functions as F
import plotly.graph_objects as go
from plotly.subplots import make_subplots

# Préparer les variables
df_ts = (
    df
    .filter(
        (F.col("Trip_Total") > 0) &
        (F.col("Trip_Seconds") > 0) &
        (F.col("Trip_Miles") > 0) &
        F.col("Trip_Start_Timestamp").isNotNull()
    )
    .withColumn("hour", F.hour(F.col("Trip_Start_Timestamp")))
    .withColumn(
        "speed_kmh",
        (F.col("Trip_Miles") * 1.609) / (F.col("Trip_Seconds") / 3600)
    )
    .filter(
        F.col("speed_kmh").isNotNull() &
        F.col("hour").isNotNull() &
        (F.col("speed_kmh") > 0) &
        (F.col("speed_kmh") < 120)
    )
)

# Agréger par heure
df_agg = (
    df_ts
    .groupBy("hour")
    .agg(
        F.count("Trip_ID").alias("nb_trips"),
        F.avg("Trip_Total").alias("avg_price"),
        F.expr("percentile_approx(speed_kmh, 0.5)").alias("median_speed_kmh")
    )
    .select("hour", "nb_trips", "avg_price", "median_speed_kmh")
    .orderBy("hour")
    .toPandas()
)

# Afficher les trois graphiques
fig = make_subplots(
    rows=3,
    cols=1,
    subplot_titles=(
        "Nombre de trajets par heure (demande)",
        "Prix moyen par heure ($)",
        "Vitesse médiane par heure (km/h)"
    ),
    vertical_spacing=0.12
)

fig.add_trace(
    go.Scatter(
        x=df_agg["hour"],
        y=df_agg["nb_trips"],
        mode="lines+markers",
        name="Nb trajets"
    ),
    row=1,
    col=1
)

fig.add_trace(
    go.Scatter(
        x=df_agg["hour"],
        y=df_agg["avg_price"],
        mode="lines+markers",
        name="Prix moyen"
    ),
    row=2,
    col=1
)

fig.add_trace(
    go.Scatter(
        x=df_agg["hour"],
        y=df_agg["median_speed_kmh"],
        mode="lines+markers",
        name="Vitesse médiane"
    ),
    row=3,
    col=1
)

fig.update_xaxes(title_text="Heure")

fig.update_layout(
    title="Analyse temporelle des taxis de Chicago par heure",
    height=750,
    showlegend=False
)

fig.show()

For each one of the columns `n` and `a` and `m` identify a filtering condition that allows you to focus on some interesting portion rows.  Replot the time series above, restricted to these rows.

For instance the three filtering conditions could concern some geographical property, so you could plot the number of `n` values in a first region, the avarage `a` value in a second region and the median `m` value in a third region; but the filtering conditions can be as complex as you wish, 


In [15]:
from pyspark.sql import functions as F
import plotly.graph_objects as go
from plotly.subplots import make_subplots

# Filtres utilisés
core_downtown_areas = [8, 32]  # Near North Side + Loop

# Filtre pour le nombre de trajets
df_n = (
    df
    .filter(F.col("Pickup_Community_Area").isin(core_downtown_areas))
    .filter(F.col("Trip_Start_Timestamp").isNotNull())
    .withColumn("hour", F.hour("Trip_Start_Timestamp"))
    .groupBy("hour")
    .agg(F.count("Trip_ID").alias("nb_trips"))
    .orderBy("hour")
    .toPandas()
)

# Filtre pour le prix moyen
df_a = (
    df
    .filter(
        (F.col("Trip_Miles") > 10) &
        (F.col("Trip_Total") > 0) &
        F.col("Trip_Start_Timestamp").isNotNull()
    )
    .withColumn("hour", F.hour("Trip_Start_Timestamp"))
    .groupBy("hour")
    .agg(F.avg("Trip_Total").alias("avg_price"))
    .orderBy("hour")
    .toPandas()
)

# Filtre pour la vitesse
df_m = (
    df
    .filter(
        (F.col("Trip_Miles") > 0) &
        (F.col("Trip_Miles") < 3) &
        (F.col("Trip_Seconds") > 600) &
        F.col("Trip_Start_Timestamp").isNotNull()
    )
    .withColumn(
        "speed_kmh",
        (F.col("Trip_Miles") * 1.609) / (F.col("Trip_Seconds") / 3600)
    )
    .filter(
        (F.col("speed_kmh") > 0) &
        (F.col("speed_kmh") < 80)
    )
    .withColumn("hour", F.hour("Trip_Start_Timestamp"))
    .groupBy("hour")
    .agg(F.expr("percentile_approx(speed_kmh, 0.5)").alias("median_speed_kmh"))
    .orderBy("hour")
    .toPandas()
)

# Graphique
fig = make_subplots(
    rows=3,
    cols=1,
    subplot_titles=(
        "Demande dans le cœur de Chicago : Loop + Near North Side",
        "Prix moyen des très longs trajets (>10 miles)",
        "Vitesse médiane des trajets courts mais lents : congestion urbaine"
    ),
    vertical_spacing=0.12
)

fig.add_trace(
    go.Scatter(
        x=df_n["hour"],
        y=df_n["nb_trips"],
        mode="lines+markers",
        name="Demande centre"
    ),
    row=1,
    col=1
)

fig.add_trace(
    go.Scatter(
        x=df_a["hour"],
        y=df_a["avg_price"],
        mode="lines+markers",
        name="Prix longs trajets"
    ),
    row=2,
    col=1
)

fig.add_trace(
    go.Scatter(
        x=df_m["hour"],
        y=df_m["median_speed_kmh"],
        mode="lines+markers",
        name="Vitesse congestion"
    ),
    row=3,
    col=1
)

fig.update_xaxes(title_text="Heure")
fig.update_layout(
    title="Séries temporelles filtrées — analyse ciblée",
    height=750,
    showlegend=False
)

fig.show()

# Geographic information

A **choropleth** maps provides a clear visual representation of how a particular variable is distributed geographically. you will need to find tools to display maps and to build choropleth maps within your notebook.
We let you look and find relevant tools to do this. 

Chose a categorical colums `c` such that the distribution of values of `c` in the dataset is interesting to analyse as a function of the geographical area. For instance `c` could be a person gender, and you are interested in counting how many rows have `c="Female"`, and how many rows have `c = "X"` in each geographical area. 

1. Choose at least two values of `c` you want to concentrate on, say `v1` and `v2`. Build a choropleth map where the color of each geographical area is a function of
    1. number of rows having `c = v1` in that area
    2. number of rows having `c = v2` in that area

In [16]:
from pyspark.sql import functions as F
import plotly.express as px
import pandas as pd
import requests
import json

# Compter Cash et Credit Card par zone

df_pay = (
    df
    .filter(
        F.col("Pickup_Community_Area").isNotNull() &
        F.col("Payment_Type").isNotNull() &
        F.col("Payment_Type").isin("Credit Card", "Cash")
    )
    .groupBy("Pickup_Community_Area", "Payment_Type")
    .agg(F.count("Trip_ID").alias("count"))
    .select("Pickup_Community_Area", "Payment_Type", "count")
    .toPandas()
)

df_pivot = (
    df_pay
    .pivot(
        index="Pickup_Community_Area",
        columns="Payment_Type",
        values="count"
    )
    .reset_index()
)

df_pivot.columns.name = None

df_pivot = df_pivot.rename(columns={
    "Credit Card": "credit_card",
    "Cash": "cash"
})

if "credit_card" not in df_pivot.columns:
    df_pivot["credit_card"] = 0

if "cash" not in df_pivot.columns:
    df_pivot["cash"] = 0

df_pivot["Pickup_Community_Area"] = df_pivot["Pickup_Community_Area"].astype(int)
df_pivot = df_pivot.fillna(0)

# Charger la carte des zones

geojson_urls = [
    # Lien Socrata
    "https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000",

    # Autre lien Socrata
    "https://data.cityofchicago.org/api/geospatial/cauq-8yn6?method=export&format=GeoJSON",

    # Lien de secours
    "https://raw.githubusercontent.com/RandomFractals/ChicagoCrimes/master/data/chicago-community-areas.geojson"
]

headers = {
    "User-Agent": "Mozilla/5.0"
}

geojson_data = None
used_url = None

for url in geojson_urls:
    try:
        r = requests.get(url, headers=headers, timeout=30)
        r.raise_for_status()
        candidate = r.json()

        if candidate.get("type") == "FeatureCollection" and "features" in candidate:
            geojson_data = candidate
            used_url = url
            break

    except Exception as e:
        print("URL échouée :", url)
        print("Erreur :", e)

if geojson_data is None:
    raise Exception("Impossible de charger un GeoJSON valide des Community Areas.")

print("GeoJSON utilisé :", used_url)
print("Nombre de zones chargées :", len(geojson_data["features"]))

# Trouver la colonne de zone

print("Exemple de propriétés GeoJSON :")
print(geojson_data["features"][0]["properties"])

possible_area_keys = [
    "area_numbe",
    "area_num_1",
    "area_num",
    "area",
    "community_area",
    "community"
]

area_key = None

for key in possible_area_keys:
    if key in geojson_data["features"][0]["properties"]:
        area_key = key
        break

if area_key is None:
    raise Exception(
        "Impossible de trouver la colonne du numéro de Community Area. "
        "Regarde les propriétés affichées juste au-dessus."
    )

print("Colonne utilisée pour matcher les zones :", area_key)

# Ajouter un id de zone
for feat in geojson_data["features"]:
    feat["id"] = int(float(feat["properties"][area_key]))

# Carte Credit Card

fig1 = px.choropleth_mapbox(
    df_pivot,
    geojson=geojson_data,
    locations="Pickup_Community_Area",
    color="credit_card",
    featureidkey="id",
    mapbox_style="carto-positron",
    center={"lat": 41.85, "lon": -87.65},
    zoom=9,
    opacity=0.75,
    title="Nombre de paiements par carte bancaire par zone de pickup",
    labels={
        "credit_card": "Nombre de paiements Credit Card",
        "Pickup_Community_Area": "Community Area"
    },
    color_continuous_scale="Blues",
    height=650
)

fig1.show()

# Carte Cash

fig2 = px.choropleth_mapbox(
    df_pivot,
    geojson=geojson_data,
    locations="Pickup_Community_Area",
    color="cash",
    featureidkey="id",
    mapbox_style="carto-positron",
    center={"lat": 41.85, "lon": -87.65},
    zoom=9,
    opacity=0.75,
    title="Nombre de paiements en cash par zone de pickup",
    labels={
        "cash": "Nombre de paiements Cash",
        "Pickup_Community_Area": "Community Area"
    },
    color_continuous_scale="Oranges",
    height=650
)

fig2.show()

GeoJSON utilisé : https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000
Nombre de zones chargées : 77
Exemple de propriétés GeoJSON :
{'community': 'ROGERS PARK', 'shape_area': '51259902.4506', 'area_num_1': '1', 'area_numbe': '1', 'shape_len': '34052.3975757'}
Colonne utilisée pour matcher les zones : area_numbe


2. Come up with a numerical indicator you can associate to each row, by combining some of its numerical columns (for instace say the rows describe births, you could take the ratio between baby weight and height for each birth). Then build a choropleth map where the color of each geographical area is a function of 
    1. the ratio between the number of rows having `c = v1` and the the number of rows having `c = v2` in that area
    1. the average indicator value for rows located in that area.

In [19]:
from pyspark.sql import functions as F
import plotly.express as px
import pandas as pd
import requests

# Créer price_per_mile

df_adv = (
    df
    .filter(
        (F.col("Trip_Miles") > 0) &
        (F.col("Trip_Total") > 0) &
        F.col("Pickup_Community_Area").isNotNull() &
        F.col("Payment_Type").isNotNull() &
        F.col("Payment_Type").isin("Credit Card", "Cash")
    )
    .withColumn("price_per_mile", F.col("Trip_Total") / F.col("Trip_Miles"))
    .filter(
        (F.col("price_per_mile") > 0) &
        (F.col("price_per_mile") <= 30)
    )
)

# Agréger par zone

df_agg_spark = (
    df_adv
    .groupBy("Pickup_Community_Area")
    .agg(
        F.sum(
            F.when(F.col("Payment_Type") == "Credit Card", 1).otherwise(0)
        ).alias("count_cc"),

        F.sum(
            F.when(F.col("Payment_Type") == "Cash", 1).otherwise(0)
        ).alias("count_cash"),

        F.count("Trip_ID").alias("total_trips"),

        F.avg("price_per_mile").alias("avg_price_per_mile")
    )
    # Éviter la division par zéro
    .withColumn(
        "ratio_payment",
        (F.col("count_cc") + F.lit(1)) / (F.col("count_cash") + F.lit(1))
    )
    # Garder les zones avec assez de données
    .filter(F.col("total_trips") >= 50)
)

df_agg = df_agg_spark.toPandas()

df_agg["Pickup_Community_Area"] = df_agg["Pickup_Community_Area"].astype(int)
df_agg["count_cc"] = df_agg["count_cc"].astype(int)
df_agg["count_cash"] = df_agg["count_cash"].astype(int)
df_agg["total_trips"] = df_agg["total_trips"].astype(int)

print(df_agg.head())

# Charger la carte des zones

geojson_urls = [
    # Lien Socrata
    "https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000",

    # Autre lien Socrata
    "https://data.cityofchicago.org/api/geospatial/cauq-8yn6?method=export&format=GeoJSON",

    # Autre lien possible
    "https://data.cityofchicago.org/api/geospatial/cauq-8yn6?method=export&type=GeoJSON",

    # Lien de secours
    "https://raw.githubusercontent.com/RandomFractals/ChicagoCrimes/master/data/chicago-community-areas.geojson"
]

headers = {
    "User-Agent": "Mozilla/5.0"
}

geojson_data = None
used_url = None

for url in geojson_urls:
    try:
        r = requests.get(url, headers=headers, timeout=30)
        r.raise_for_status()
        candidate = r.json()

        if candidate.get("type") == "FeatureCollection" and "features" in candidate:
            geojson_data = candidate
            used_url = url
            break
        else:
            print("URL non GeoJSON valide :", url)
            print("Clés reçues :", candidate.keys())

    except Exception as e:
        print("URL échouée :", url)
        print("Erreur :", e)

if geojson_data is None:
    raise Exception("Impossible de charger un GeoJSON valide des Community Areas.")

print("GeoJSON utilisé :", used_url)
print("Nombre de zones GeoJSON :", len(geojson_data["features"]))

# Trouver la colonne de zone

print("Exemple propriétés GeoJSON :")
print(geojson_data["features"][0]["properties"])

possible_area_keys = [
    "area_numbe",
    "area_num_1",
    "area_num",
    "area",
    "community_area",
    "community"
]

area_key = None

for key in possible_area_keys:
    if key in geojson_data["features"][0]["properties"]:
        area_key = key
        break

if area_key is None:
    raise Exception(
        "Impossible de trouver la clé du numéro de Community Area. "
        "Regarde les propriétés affichées ci-dessus."
    )

print("Clé utilisée pour matcher les zones :", area_key)

for feat in geojson_data["features"]:
    feat["id"] = int(float(feat["properties"][area_key]))

# Carte du ratio Credit Card / Cash

fig1 = px.choropleth_mapbox(
    df_agg,
    geojson=geojson_data,
    locations="Pickup_Community_Area",
    color="ratio_payment",
    featureidkey="id",
    mapbox_style="carto-positron",
    center={"lat": 41.85, "lon": -87.65},
    zoom=9,
    opacity=0.75,
    title="Ratio Credit Card / Cash par zone de pickup",
    labels={
        "ratio_payment": "Ratio Credit Card / Cash",
        "Pickup_Community_Area": "Community Area"
    },
    color_continuous_scale="RdYlGn",
    height=650,
    hover_data={
        "Pickup_Community_Area": True,
        "count_cc": True,
        "count_cash": True,
        "total_trips": True,
        "ratio_payment": ":.2f",
        "avg_price_per_mile": ":.2f"
    }
)

fig1.show()

# Carte du prix moyen par mile

fig2 = px.choropleth_mapbox(
    df_agg,
    geojson=geojson_data,
    locations="Pickup_Community_Area",
    color="avg_price_per_mile",
    featureidkey="id",
    mapbox_style="carto-positron",
    center={"lat": 41.85, "lon": -87.65},
    zoom=9,
    opacity=0.75,
    title="Prix moyen par mile par zone de pickup",
    labels={
        "avg_price_per_mile": "Prix moyen par mile ($/mile)",
        "Pickup_Community_Area": "Community Area"
    },
    color_continuous_scale="Viridis",
    height=650,
    hover_data={
        "Pickup_Community_Area": True,
        "count_cc": True,
        "count_cash": True,
        "total_trips": True,
        "ratio_payment": ":.2f",
        "avg_price_per_mile": ":.2f"
    }
)

fig2.show()

   Pickup_Community_Area  count_cc  count_cash  total_trips  \
0                     73        41         631          672   
1                     56      6250        4796        11046   
2                     16       600        2597         3197   
3                     35      1530        3158         4688   
4                     62        16          65           81   

   avg_price_per_mile  ratio_payment  
0            5.514806       0.066456  
1            5.958400       1.303106  
2            5.454162       0.231332  
3            4.990590       0.484647  
4            6.672241       0.257576  
GeoJSON utilisé : https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000
Nombre de zones GeoJSON : 77
Exemple propriétés GeoJSON :
{'community': 'ROGERS PARK', 'shape_area': '51259902.4506', 'area_num_1': '1', 'area_numbe': '1', 'shape_len': '34052.3975757'}
Clé utilisée pour matcher les zones : area_numbe


In [23]:
from pyspark.sql import functions as F
df.where(F.col("Pickup_Community_Area")==47).show()

+--------------------+--------------------+--------------------+-------------------+------------+----------+-------------------+--------------------+---------------------+----------------------+-----+----+-----+------+----------+------------+--------------------+------------------------+-------------------------+-------------------------+--------------------------+----------+
|             Trip_ID|             Taxi_ID|Trip_Start_Timestamp| Trip_End_Timestamp|Trip_Seconds|Trip_Miles|Pickup_Census_Tract|Dropoff_Census_Tract|Pickup_Community_Area|Dropoff_Community_Area| Fare|Tips|Tolls|Extras|Trip_Total|Payment_Type|             Company|Pickup_Centroid_Latitude|Pickup_Centroid_Longitude|Dropoff_Centroid_Latitude|Dropoff_Centroid_Longitude|Trip_month|
+--------------------+--------------------+--------------------+-------------------+------------+----------+-------------------+--------------------+---------------------+----------------------+-----+----+-----+------+----------+------------+

3. Identify a temporal column `t` (date, year, etc.) Build an interactive choropleth with a slider allowing the user to select a time interval for `t` among a few predefined ones. The color of each geographical area must be a function of the average number of rows  having the same value of `t` and having `c = v2` in that area, during the chosen time interval (for instance if `t` is a date, `c` is a gender and rows are births, the color of an area could be a function of the average number of female births per day in the chosen date interval in the area)

In [24]:
from pyspark.sql import functions as F
import plotly.express as px
import pandas as pd
import requests

# Créer les trimestres

df_cash = (
    df
    .filter(
        (F.col("Payment_Type") == "Cash") &
        F.col("Pickup_Community_Area").isNotNull() &
        F.col("Trip_month").isNotNull()
    )
    .withColumn("Trip_month", F.col("Trip_month").cast("int"))
    .filter((F.col("Trip_month") >= 1) & (F.col("Trip_month") <= 12))
    .withColumn(
        "quarter",
        F.when(F.col("Trip_month").between(1, 3), "Jan-Mar")
         .when(F.col("Trip_month").between(4, 6), "Apr-Jun")
         .when(F.col("Trip_month").between(7, 9), "Jul-Sep")
         .when(F.col("Trip_month").between(10, 12), "Oct-Dec")
    )
    .filter(F.col("quarter").isNotNull())
)

# Compter les trajets Cash
# On calcule une moyenne par mois
# t correspond au mois du trajet

df_monthly = (
    df_cash
    .groupBy("quarter", "Trip_month", "Pickup_Community_Area")
    .agg(F.count("Trip_ID").alias("cash_count_month"))
)

# Moyenne par trimestre et par zone

df_grouped = (
    df_monthly
    .groupBy("quarter", "Pickup_Community_Area")
    .agg(
        F.avg("cash_count_month").alias("avg_cash_trips"),
        F.sum("cash_count_month").alias("total_cash_trips"),
        F.countDistinct("Trip_month").alias("months_available")
    )
    .filter(F.col("months_available") > 0)
    .toPandas()
)

df_grouped["Pickup_Community_Area"] = df_grouped["Pickup_Community_Area"].astype(int)

# Charger la carte des zones

geojson_urls = [
    "https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000",
    "https://data.cityofchicago.org/api/geospatial/cauq-8yn6?method=export&format=GeoJSON",
    "https://data.cityofchicago.org/api/geospatial/cauq-8yn6?method=export&type=GeoJSON",
    "https://raw.githubusercontent.com/RandomFractals/ChicagoCrimes/master/data/chicago-community-areas.geojson"
]

headers = {"User-Agent": "Mozilla/5.0"}

geojson_data = None
used_url = None

for url in geojson_urls:
    try:
        r = requests.get(url, headers=headers, timeout=30)
        r.raise_for_status()
        candidate = r.json()

        if candidate.get("type") == "FeatureCollection" and "features" in candidate:
            geojson_data = candidate
            used_url = url
            break
        else:
            print("URL non GeoJSON valide :", url)
            print("Clés reçues :", candidate.keys())

    except Exception as e:
        print("URL échouée :", url)
        print("Erreur :", e)

if geojson_data is None:
    raise Exception("Impossible de charger un GeoJSON valide des Community Areas.")

print("GeoJSON utilisé :", used_url)
print("Nombre de zones GeoJSON :", len(geojson_data["features"]))

# Trouver la clé de zone

print("Exemple propriétés GeoJSON :")
print(geojson_data["features"][0]["properties"])

possible_area_keys = [
    "area_numbe",
    "area_num_1",
    "area_num",
    "area",
    "community_area",
    "community"
]

area_key = None

for key in possible_area_keys:
    if key in geojson_data["features"][0]["properties"]:
        area_key = key
        break

if area_key is None:
    raise Exception(
        "Impossible de trouver la clé du numéro de Community Area. "
        "Regarde les propriétés affichées ci-dessus."
    )

print("Clé utilisée pour matcher les zones :", area_key)

for feat in geojson_data["features"]:
    feat["id"] = int(float(feat["properties"][area_key]))

# Ordonner les trimestres

quarter_order = ["Jan-Mar", "Apr-Jun", "Jul-Sep", "Oct-Dec"]

df_grouped["quarter"] = pd.Categorical(
    df_grouped["quarter"],
    categories=quarter_order,
    ordered=True
)

df_grouped = df_grouped.sort_values(["quarter", "Pickup_Community_Area"])

# Carte avec slider

max_color = df_grouped["avg_cash_trips"].quantile(0.95)

fig = px.choropleth_mapbox(
    df_grouped,
    geojson=geojson_data,
    locations="Pickup_Community_Area",
    color="avg_cash_trips",
    featureidkey="id",
    animation_frame="quarter",
    mapbox_style="carto-positron",
    center={"lat": 41.85, "lon": -87.65},
    zoom=9,
    opacity=0.75,
    title="Nombre moyen mensuel de trajets Cash par zone — slider trimestriel",
    labels={
        "avg_cash_trips": "Moyenne trajets Cash / mois",
        "Pickup_Community_Area": "Community Area",
        "quarter": "Trimestre"
    },
    color_continuous_scale="YlOrRd",
    height=650,
    range_color=[0, max_color],
    hover_data={
        "Pickup_Community_Area": True,
        "quarter": True,
        "avg_cash_trips": ":.0f",
        "total_cash_trips": True,
        "months_available": True
    }
)

fig.update_layout(
    sliders=[{
        "currentvalue": {"prefix": "Période : "},
        "pad": {"t": 50}
    }]
)

fig.show()

GeoJSON utilisé : https://data.cityofchicago.org/resource/igwz-8jzy.geojson?$limit=5000
Nombre de zones GeoJSON : 77
Exemple propriétés GeoJSON :
{'community': 'ROGERS PARK', 'shape_area': '51259902.4506', 'area_num_1': '1', 'area_numbe': '1', 'shape_len': '34052.3975757'}
Clé utilisée pour matcher les zones : area_numbe


You can use a different column `c` for each of the items above if you prefer. 